# ML for Gas Adsorption

## -1. Only if you run this notebook on Colab

If you use this notebook on Colab, please uncomment the lines below (remove the `#`) and execute the cell.

In [1]:
#import sys
#!{sys.executable} -m pip install -U pandas-profiling[notebook]
#!jupyter nbextension enable --py widgetsnbextension
#!pip install --upgrade pandas sklearn holoviews bokeh plotly matplotlib
#!wget https://raw.githubusercontent.com/kjappelbaum/ml_molsim/2022/descriptornames.py
#!mkdir data
#!cd data && wget https://github.com/kjappelbaum/ml_molsim/raw/2022/data/data.csv
#!cd data && wget https://github.com/kjappelbaum/ml_molsim/raw/2022/data/features.csv
# import os, holoviews as hv
# os.environ['HV_DOC_HTML'] = 'true'

## Import packages we will need

In [2]:
# basics
import os
import numpy as np
import pprint as pp

# pandas is used to read/process data
import pandas as pd

# machine learning dependencies
# scaling of data
from sklearn.preprocessing import StandardScaler, MinMaxScaler, RobustScaler
# train/test split
from sklearn.model_selection import train_test_split
# model selection
from sklearn.model_selection import GridSearchCV, RandomizedSearchCV
# the KRR model
from sklearn.kernel_ridge import KernelRidge
# linear model
from sklearn.linear_model import LinearRegression
# pipeline to streamline modeling pipelines
from sklearn.pipeline import Pipeline
# principal component analysis
from sklearn.decomposition import PCA
# polynomial kernel
from sklearn.metrics.pairwise import polynomial_kernel
# Dummy model as baseline
from sklearn.dummy import DummyClassifier, DummyRegressor
# Variance Threshold for feature selection
from sklearn.feature_selection import VarianceThreshold, SelectFromModel
# metrics to measure model performance
from sklearn.metrics import (accuracy_score, precision_score, recall_score, f1_score,
                             mean_absolute_error, mean_squared_error, max_error)

# save/load models
import joblib

# For the permutation importance implementation
from joblib import Parallel
from joblib import delayed
from sklearn.metrics import check_scoring
from sklearn.utils import Bunch
from sklearn.utils import check_random_state
from sklearn.utils import check_array

# Interactive notebook plots (Plotly is included in environment.yml).
import plotly.graph_objects as go
import plotly.io as pio
from plotly.subplots import make_subplots
from plotly.colors import sample_colorscale

# Support JupyterLab and classic notebooks, including offline use.
pio.renderers.default = 'plotly_mimetype+notebook'
PLOT_CONFIG = {'scrollZoom': True, 'displaylogo': False, 'responsive': True}
MAGMA_COLORS = sample_colorscale('Magma', [0.25, 0.65])


RANDOM_SEED = 4242424242
DATA_DIR = 'data'
DATA_FILE = os.path.join(DATA_DIR, 'data.csv')

np.random.seed(RANDOM_SEED)


In [3]:

other_descriptors = ["CellV [A^3]"]

geometric_descriptors = [
    "Di",
    "Df",
    "Dif",
    "density [g/cm^3]",
    "total_SA_volumetric",
    "total_SA_gravimetric",
    "total_POV_volumetric",
    "total_POV_gravimetric",
]

linker_descriptors = [
    "f-lig-chi-0",
    "f-lig-chi-1",
    "f-lig-chi-2",
    "f-lig-chi-3",
    "f-lig-Z-0",
    "f-lig-Z-1",
    "f-lig-Z-2",
    "f-lig-Z-3",
    "f-lig-I-0",
    "f-lig-I-1",
    "f-lig-I-2",
    "f-lig-I-3",
    "f-lig-T-0",
    "f-lig-T-1",
    "f-lig-T-2",
    "f-lig-T-3",
    "f-lig-S-0",
    "f-lig-S-1",
    "f-lig-S-2",
    "f-lig-S-3",
    "lc-chi-0-all",
    "lc-chi-1-all",
    "lc-chi-2-all",
    "lc-chi-3-all",
    "lc-Z-0-all",
    "lc-Z-1-all",
    "lc-Z-2-all",
    "lc-Z-3-all",
    "lc-I-0-all",
    "lc-I-1-all",
    "lc-I-2-all",
    "lc-I-3-all",
    "lc-T-0-all",
    "lc-T-1-all",
    "lc-T-2-all",
    "lc-T-3-all",
    "lc-S-0-all",
    "lc-S-1-all",
    "lc-S-2-all",
    "lc-S-3-all",
    "lc-alpha-0-all",
    "lc-alpha-1-all",
    "lc-alpha-2-all",
    "lc-alpha-3-all",
    "D_lc-chi-0-all",
    "D_lc-chi-1-all",
    "D_lc-chi-2-all",
    "D_lc-chi-3-all",
    "D_lc-Z-0-all",
    "D_lc-Z-1-all",
    "D_lc-Z-2-all",
    "D_lc-Z-3-all",
    "D_lc-I-0-all",
    "D_lc-I-1-all",
    "D_lc-I-2-all",
    "D_lc-I-3-all",
    "D_lc-T-0-all",
    "D_lc-T-1-all",
    "D_lc-T-2-all",
    "D_lc-T-3-all",
    "D_lc-S-0-all",
    "D_lc-S-1-all",
    "D_lc-S-2-all",
    "D_lc-S-3-all",
    "D_lc-alpha-0-all",
    "D_lc-alpha-1-all",
    "D_lc-alpha-2-all",
    "D_lc-alpha-3-all",
]

metalcenter_descriptors = [
    "mc_CRY-chi-0-all",
    "mc_CRY-chi-1-all",
    "mc_CRY-chi-2-all",
    "mc_CRY-chi-3-all",
    "mc_CRY-Z-0-all",
    "mc_CRY-Z-1-all",
    "mc_CRY-Z-2-all",
    "mc_CRY-Z-3-all",
    "mc_CRY-I-0-all",
    "mc_CRY-I-1-all",
    "mc_CRY-I-2-all",
    "mc_CRY-I-3-all",
    "mc_CRY-T-0-all",
    "mc_CRY-T-1-all",
    "mc_CRY-T-2-all",
    "mc_CRY-T-3-all",
    "mc_CRY-S-0-all",
    "mc_CRY-S-1-all",
    "mc_CRY-S-2-all",
    "mc_CRY-S-3-all",
    "D_mc_CRY-chi-0-all",
    "D_mc_CRY-chi-1-all",
    "D_mc_CRY-chi-2-all",
    "D_mc_CRY-chi-3-all",
    "D_mc_CRY-Z-0-all",
    "D_mc_CRY-Z-1-all",
    "D_mc_CRY-Z-2-all",
    "D_mc_CRY-Z-3-all",
    "D_mc_CRY-I-0-all",
    "D_mc_CRY-I-1-all",
    "D_mc_CRY-I-2-all",
    "D_mc_CRY-I-3-all",
    "D_mc_CRY-T-0-all",
    "D_mc_CRY-T-1-all",
    "D_mc_CRY-T-2-all",
    "D_mc_CRY-T-3-all",
    "D_mc_CRY-S-0-all",
    "D_mc_CRY-S-1-all",
    "D_mc_CRY-S-2-all",
    "D_mc_CRY-S-3-all",
]

functionalgroup_descriptors = [
    "func-chi-0-all",
    "func-chi-1-all",
    "func-chi-2-all",
    "func-chi-3-all",
    "func-Z-0-all",
    "func-Z-1-all",
    "func-Z-2-all",
    "func-Z-3-all",
    "func-I-0-all",
    "func-I-1-all",
    "func-I-2-all",
    "func-I-3-all",
    "func-T-0-all",
    "func-T-1-all",
    "func-T-2-all",
    "func-T-3-all",
    "func-S-0-all",
    "func-S-1-all",
    "func-S-2-all",
    "func-S-3-all",
    "func-alpha-0-all",
    "func-alpha-1-all",
    "func-alpha-2-all",
    "func-alpha-3-all",
    "D_func-chi-0-all",
    "D_func-chi-1-all",
    "D_func-chi-2-all",
    "D_func-chi-3-all",
    "D_func-Z-0-all",
    "D_func-Z-1-all",
    "D_func-Z-2-all",
    "D_func-Z-3-all",
    "D_func-I-0-all",
    "D_func-I-1-all",
    "D_func-I-2-all",
    "D_func-I-3-all",
    "D_func-T-0-all",
    "D_func-T-1-all",
    "D_func-T-2-all",
    "D_func-T-3-all",
    "D_func-S-0-all",
    "D_func-S-1-all",
    "D_func-S-2-all",
    "D_func-S-3-all",
    "D_func-alpha-0-all",
    "D_func-alpha-1-all",
    "D_func-alpha-2-all",
    "D_func-alpha-3-all",
]


summed_linker_descriptors = [
    "sum-f-lig-chi-0",
    "sum-f-lig-chi-1",
    "sum-f-lig-chi-2",
    "sum-f-lig-chi-3",
    "sum-f-lig-Z-0",
    "sum-f-lig-Z-1",
    "sum-f-lig-Z-2",
    "sum-f-lig-Z-3",
    "sum-f-lig-I-0",
    "sum-f-lig-I-1",
    "sum-f-lig-I-2",
    "sum-f-lig-I-3",
    "sum-f-lig-T-0",
    "sum-f-lig-T-1",
    "sum-f-lig-T-2",
    "sum-f-lig-T-3",
    "sum-f-lig-S-0",
    "sum-f-lig-S-1",
    "sum-f-lig-S-2",
    "sum-f-lig-S-3",
    "sum-lc-chi-0-all",
    "sum-lc-chi-1-all",
    "sum-lc-chi-2-all",
    "sum-lc-chi-3-all",
    "sum-lc-Z-0-all",
    "sum-lc-Z-1-all",
    "sum-lc-Z-2-all",
    "sum-lc-Z-3-all",
    "sum-lc-I-0-all",
    "sum-lc-I-1-all",
    "sum-lc-I-2-all",
    "sum-lc-I-3-all",
    "sum-lc-T-0-all",
    "sum-lc-T-1-all",
    "sum-lc-T-2-all",
    "sum-lc-T-3-all",
    "sum-lc-S-0-all",
    "sum-lc-S-1-all",
    "sum-lc-S-2-all",
    "sum-lc-S-3-all",
    "sum-lc-alpha-0-all",
    "sum-lc-alpha-1-all",
    "sum-lc-alpha-2-all",
    "sum-lc-alpha-3-all",
    "sum-D_lc-chi-0-all",
    "sum-D_lc-chi-1-all",
    "sum-D_lc-chi-2-all",
    "sum-D_lc-chi-3-all",
    "sum-D_lc-Z-0-all",
    "sum-D_lc-Z-1-all",
    "sum-D_lc-Z-2-all",
    "sum-D_lc-Z-3-all",
    "sum-D_lc-I-0-all",
    "sum-D_lc-I-1-all",
    "sum-D_lc-I-2-all",
    "sum-D_lc-I-3-all",
    "sum-D_lc-T-0-all",
    "sum-D_lc-T-1-all",
    "sum-D_lc-T-2-all",
    "sum-D_lc-T-3-all",
    "sum-D_lc-S-0-all",
    "sum-D_lc-S-1-all",
    "sum-D_lc-S-2-all",
    "sum-D_lc-S-3-all",
    "sum-D_lc-alpha-0-all",
    "sum-D_lc-alpha-1-all",
    "sum-D_lc-alpha-2-all",
    "sum-D_lc-alpha-3-all",
]

summed_metalcenter_descriptors = [
    "sum-mc_CRY-chi-0-all",
    "sum-mc_CRY-chi-1-all",
    "sum-mc_CRY-chi-2-all",
    "sum-mc_CRY-chi-3-all",
    "sum-mc_CRY-Z-0-all",
    "sum-mc_CRY-Z-1-all",
    "sum-mc_CRY-Z-2-all",
    "sum-mc_CRY-Z-3-all",
    "sum-mc_CRY-I-0-all",
    "sum-mc_CRY-I-1-all",
    "sum-mc_CRY-I-2-all",
    "sum-mc_CRY-I-3-all",
    "sum-mc_CRY-T-0-all",
    "sum-mc_CRY-T-1-all",
    "sum-mc_CRY-T-2-all",
    "sum-mc_CRY-T-3-all",
    "sum-mc_CRY-S-0-all",
    "sum-mc_CRY-S-1-all",
    "sum-mc_CRY-S-2-all",
    "sum-mc_CRY-S-3-all",
    "sum-D_mc_CRY-chi-0-all",
    "sum-D_mc_CRY-chi-1-all",
    "sum-D_mc_CRY-chi-2-all",
    "sum-D_mc_CRY-chi-3-all",
    "sum-D_mc_CRY-Z-0-all",
    "sum-D_mc_CRY-Z-1-all",
    "sum-D_mc_CRY-Z-2-all",
    "sum-D_mc_CRY-Z-3-all",
    "sum-D_mc_CRY-I-0-all",
    "sum-D_mc_CRY-I-1-all",
    "sum-D_mc_CRY-I-2-all",
    "sum-D_mc_CRY-I-3-all",
    "sum-D_mc_CRY-T-0-all",
    "sum-D_mc_CRY-T-1-all",
    "sum-D_mc_CRY-T-2-all",
    "sum-D_mc_CRY-T-3-all",
    "sum-D_mc_CRY-S-0-all",
    "sum-D_mc_CRY-S-1-all",
    "sum-D_mc_CRY-S-2-all",
    "sum-D_mc_CRY-S-3-all",
]

summed_functionalgroup_descriptors = [
    "sum-func-chi-0-all",
    "sum-func-chi-1-all",
    "sum-func-chi-2-all",
    "sum-func-chi-3-all",
    "sum-func-Z-0-all",
    "sum-func-Z-1-all",
    "sum-func-Z-2-all",
    "sum-func-Z-3-all",
    "sum-func-I-0-all",
    "sum-func-I-1-all",
    "sum-func-I-2-all",
    "sum-func-I-3-all",
    "sum-func-T-0-all",
    "sum-func-T-1-all",
    "sum-func-T-2-all",
    "sum-func-T-3-all",
    "sum-func-S-0-all",
    "sum-func-S-1-all",
    "sum-func-S-2-all",
    "sum-func-S-3-all",
    "sum-func-alpha-0-all",
    "sum-func-alpha-1-all",
    "sum-func-alpha-2-all",
    "sum-func-alpha-3-all",
    "sum-D_func-chi-0-all",
    "sum-D_func-chi-1-all",
    "sum-D_func-chi-2-all",
    "sum-D_func-chi-3-all",
    "sum-D_func-Z-0-all",
    "sum-D_func-Z-1-all",
    "sum-D_func-Z-2-all",
    "sum-D_func-Z-3-all",
    "sum-D_func-I-0-all",
    "sum-D_func-I-1-all",
    "sum-D_func-I-2-all",
    "sum-D_func-I-3-all",
    "sum-D_func-T-0-all",
    "sum-D_func-T-1-all",
    "sum-D_func-T-2-all",
    "sum-D_func-T-3-all",
    "sum-D_func-S-0-all",
    "sum-D_func-S-1-all",
    "sum-D_func-S-2-all",
    "sum-D_func-S-3-all",
    "sum-D_func-alpha-0-all",
    "sum-D_func-alpha-1-all",
    "sum-D_func-alpha-2-all",
    "sum-D_func-alpha-3-all",
]


 $\color{DarkBlue}{\textsf{Short question}}$
- We declared a global variable to fix the random seed (`RANDOM_SEED`). Why did we do this?



Fixing the random seed makes random operations reproducible, such as the train/test split and the sampling of hyperparameters. This lets us rerun the notebook and compare models on the same data split. Otherwise, a difference in scores could come from a different split rather than a better model.

## Hands-on Project: Carbon-dioxide uptake in MOFs

In this exercise we will build a model that can predict the CO$_2$ uptake of metal-organic frameworks (MOFs), which are crystalline materials consisting of inorganic metal nodes linked by organic linkers.

![MOF building principle](assets/mof_building_principle.png)

There are two main **learning goals** for this exercise: 

1. Understand the typical workflow for machine learning in materials science. We will cover exploratory data analysis (EDA) and supervised learning (KRR).

2. Get familiar with some Python packages that are useful for data analysis and visualization. 

At the end of the exercise, you will produce an interactive plot like the one below, comparing the predictions of your model against CO$_2$ computed with GCMC simulations.
The histograms show the distributions of the errors on the training set (left) and on the test set (right).



<img src="assets/result.gif" alt="Parity interactive" width="700"/>

This exercise requires a basic knowledge of Python, e.g. that you can write list comprehensions, and are able to read documentation of functions provided by Python packages.
You will be asked to provide some function arguments (indicated by `#fillme` comments).

You can execute all the following code cells by pressing SHIFT and ENTER and get informations about the functions by pressing TAB when you are between the parentheses (see the notes for more tips). 

Also the [sklearn documentation](https://scikit-learn.org/stable/user_guide.html) is a great source of reference with many explanations and examples.

In pandas dataframe (df) you can select columns using their name by running `df[columnname]`. If at any point you think that the dataset is too large for your computer, you can select a subset using `df.sample()` or by making the test set larger in the train/test split (section 2). 

## 1. Import the data

In [4]:
df = pd.read_csv(DATA_FILE)

Let's take a look at the first few rows to see if everythings seems reasonable ...

In [5]:
pd.options.display.max_columns=100
df.head()

,ASA [m^2/cm^3],CellV [A^3],Df,Di,Dif,NASA [m^2/cm^3],POAV [cm^3/g],POAVF,PONAV [cm^3/g],PONAVF,density [g/cm^3],MOFname,total_SA_volumetric,total_SA_gravimetric,total_POV_volumetric,total_POV_gravimetric,mc_CRY-chi-0-all,mc_CRY-chi-1-all,mc_CRY-chi-2-all,mc_CRY-chi-3-all,mc_CRY-Z-0-all,mc_CRY-Z-1-all,mc_CRY-Z-2-all,mc_CRY-Z-3-all,mc_CRY-I-0-all,mc_CRY-I-1-all,mc_CRY-I-2-all,mc_CRY-I-3-all,mc_CRY-T-0-all,mc_CRY-T-1-all,mc_CRY-T-2-all,mc_CRY-T-3-all,mc_CRY-S-0-all,mc_CRY-S-1-all,mc_CRY-S-2-all,mc_CRY-S-3-all,D_mc_CRY-chi-0-all,D_mc_CRY-chi-1-all,D_mc_CRY-chi-2-all,D_mc_CRY-chi-3-all,D_mc_CRY-Z-0-all,D_mc_CRY-Z-1-all,D_mc_CRY-Z-2-all,D_mc_CRY-Z-3-all,D_mc_CRY-I-0-all,D_mc_CRY-I-1-all,D_mc_CRY-I-2-all,D_mc_CRY-I-3-all,D_mc_CRY-T-0-all,D_mc_CRY-T-1-all,...,sum-D_func-I-1-all,sum-D_func-I-2-all,sum-D_func-I-3-all,sum-D_func-T-0-all,sum-D_func-T-1-all,sum-D_func-T-2-all,sum-D_func-T-3-all,sum-D_func-S-0-all,sum-D_func-S-1-all,sum-D_func-S-2-all,sum-D_func-S-3-all,sum-D_func-alpha-0-all,sum-D_func-alpha-1-all,sum-D_func-alpha-2-all,sum-D_func-alpha-3-all,sum-f-lig-chi-0,sum-f-lig-chi-1,sum-f-lig-chi-2,sum-f-lig-chi-3,sum-f-lig-Z-0,sum-f-lig-Z-1,sum-f-lig-Z-2,sum-f-lig-Z-3,sum-f-lig-I-0,sum-f-lig-I-1,sum-f-lig-I-2,sum-f-lig-I-3,sum-f-lig-T-0,sum-f-lig-T-1,sum-f-lig-T-2,sum-f-lig-T-3,sum-f-lig-S-0,sum-f-lig-S-1,sum-f-lig-S-2,sum-f-lig-S-3,MNC,MPC,pure_CO2_kH,pure_CO2_widomHOA,pure_methane_kH,pure_methane_widomHOA,pure_uptake_CO2_298.00_15000,pure_uptake_CO2_298.00_1600000,pure_uptake_methane_298.00_580000,pure_uptake_methane_298.00_6500000,logKH_CO2,logKH_CH4,CH4DC,CH4HPSTP,CH4LPSTP
0,2329.01,1251.28,6.61256,8.87694,8.48668,0.0,0.818919,0.68874,0.0,0.0,0.841035,str_m1_o10_o10_pcu_sym.102,2329.01,2769.218879,0.68874,0.818919,2.7225,22.704,20.79,63.7065,900.0,960.0,3240.0,2700.0,1.0,4.0,6.0,12.0,16.0,40.0,84.0,108.0,1.7161,3.8252,8.1744,11.6328,0.0,-7.16,-2.7,-18.81,0.0,88.0,72.0,270.0,0.0,0.0,0.0,0.0,0.0,6.0,...,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0,0.0000,0.0000,0.00,0.0,0.000,0.000,0.0,265.2557,430.3380,631.4712,602.9960,1244.0,1968.0,2658.0,1940.0,33.0,60.0,84.0,84.0,144.0,312.0,324.0,264.0,15.1977,29.9068,37.6004,33.2692,-0.550363,0.948402,0.000007,-12.903174,0.000003,-8.144317,0.111981,14.218595,1.680640,9.163066,-5.125451,-5.511444,175.569974,215.005044,39.435070
1,1983.81,1254.01,5.80566,7.13426,7.13154,0.0,0.495493,0.58032,0.0,0.0,1.171200,str_m1_o10_o10_pcu_sym.124,1983.81,1693.826844,0.58032,0.495493,2.7225,22.704,20.79,63.7065,900.0,960.0,3240.0,2700.0,1.0,4.0,6.0,12.0,16.0,40.0,84.0,108.0,1.7161,3.8252,8.1744,11.6328,0.0,-7.16,-2.7,-18.81,0.0,88.0,72.0,270.0,0.0,0.0,0.0,0.0,0.0,6.0,...,0.0,0.0,0.0,0.0,-4.0,-8.0,-7.0,0.0,0.7400,1.4800,2.75,0.0,19.400,38.800,91.9,293.2030,477.4110,720.9972,733.1770,4954.0,3288.0,5268.0,9586.0,36.0,66.0,96.0,96.0,162.0,354.0,384.0,336.0,19.5525,35.7896,48.4780,52.5818,-0.542509,1.022895,0.000031,-23.395284,0.000003,-10.208005,0.481625,9.312424,1.513152,5.908356,-4.502967,-5.505947,143.616349,193.059644,49.443295
2,2259.13,1250.58,5.99131,8.01682,7.98933,0.0,0.728036,0.65710,0.0,0.0,0.902566,str_m1_o10_o10_pcu_sym.183,2259.13,2503.008090,0.65710,0.728036,2.7225,22.704,20.79,63.7065,900.0,960.0,3240.0,2700.0,1.0,4.0,6.0,12.0,16.0,40.0,84.0,108.0,1.7161,3.8252,8.1744,11.6328,0.0,-7.16,-2.7,-18.81,0.0,88.0,72.0,270.0,0.0,0.0,0.0,0.0,0.0,6.0,...,0.0,0.0,0.0,0.0,-1.0,-4.0,0.0,0.0,0.4600,0.0400,0.24,0.0,-10.800,-20.600,-17.2,291.0765,468.3620,660.4072,696.6368,1434.0,2240.0,3100.0,2846.0,34.0,62.0,82.0,88.0,144.0,314.0,338.0,292.0,16.5226,32.0806,40.6610,39.5496,-0.758790,1.029985,0.000037,-27.155329,0.000003,-8.479801,0.401683,14.796071,1.569714,7.933198,-4.433968,-5.525707,160.238808,199.765744,39.526937
3,1424.54,1249.27,4.73477,7.05822,7.05822,0.0,0.453157,0.47338,0.0,0.0,1.044630,str_m1_o10_o10_pcu_sym.184,1424.54,1363.679006,0.47338,0.453157,2.7225,22.704,20.79,63.7065,900.0,960.0,3240.0,2700.0,1.0,4.0,6.0,12.0,16.0,40.0,84.0,108.0,1.7161,3.8252,8.1744,11.6328,0.0,-7.16,-2.7,-18.81,0.0,88.0,72.0,270.0

<details>
<summary> <font color='green'>Click here for a hint</font></summary>
<ul>
    <li>Use something like <code>pd.options.display.max_columns=100</code> to adjust how many columns are shown.<code>pd.options.display.max_columns=100</code>  would show at maximum 100 columns. </li>
</ul>
</details>

Let's also get some basic information ...

In [6]:
df.info()

<class 'pandas.DataFrame'>
RangeIndex: 17379 entries, 0 to 17378
Columns: 343 entries, ASA [m^2/cm^3] to CH4LPSTP
dtypes: float64(342), str(1)
memory usage: 45.5 MB


 $\color{DarkBlue}{\textsf{Short question}}$
- How many materials are in the dataset? 
- Which datatypes do we deal with?



The dataset contains 17,379 materials and 343 columns. The `df.info()` output shows 342 `float64` columns for numerical values, including the descriptors and gas uptakes, and one string column containing the MOF names (`MOFname`). The binary target added later contains integer labels, 0 and 1.


Below, we define three global variables (hence upper case), which are the *names* of our feature and target columns. We will use the `TARGET` for the actual regression and the `TARGET_BINARY` only for the stratified train/test split. The `FEATURES` variable is a list of column names of our dataframe.

In [7]:
TARGET = "pure_uptake_CO2_298.00_1600000"
TARGET_BINARY = "target_binned"  # will be created later
FEATURES = (
    geometric_descriptors
    + summed_functionalgroup_descriptors
    + summed_linker_descriptors
    + summed_metalcenter_descriptors
)


As descriptors we will use geometric properties such as density, pore volume, etc. and [revised autocorrelation functions](https://pubs.acs.org/doi/abs/10.1021/acs.jpca.7b08750) (RACs) that have been optimized for describing inorganic compounds ([and recently adapated for MOFs](https://www.nature.com/articles/s41467-020-17755-8))

Examples for pore geometry descriptors (in `geometric_descriptors`) include: $D_i$ (the size of the largest included sphere), $D_f$ (the largest free sphere), and $D_{if}$ (the largest included free sphere) along the pore $-$ three ways of characterizing pore size. 

![pore diameters](assets/spheres.png)

Also included are the surface area (SA) of the pore, and the probe-occupiable pore volume (POV).
More details on the description of pore geometries can be found in [Ongari et al.](https://pubs.acs.org/doi/abs/10.1021/acs.langmuir.7b01682)

RACs (in the lists starting with `summed_...`) operate on the structure graph and encode information about the metal center, linkers and the functional groups as differences or products of heuristics that are relevant for inorganic chemistry, such as electronegativity ($\chi$), connectivity ($T$), identity ($I$), covalent radii ($S$), and nuclear charge ($Z$).


<img src="assets/racs.png" alt="RACs scheme from the lecture" width="700"/>

The number in the descriptornames shows the coordination shell that was considered in the calculation of the RACs.

The target we use for this application is the high-pressure CO$_2$ uptake. This is the amount of CO$_2$ (mmol) the MOF can load per gram.

## 2. Split the data

Next, we split our data into a training set and a test set.

In order to prevent *any* information of the test set from leaking into our model, we split *before* starting to analyze or transform our data. For more details on why this matters, see [chapter 7.10.2 of Elements of Statistical Learning](https://web.stanford.edu/~hastie/ElemStatLearn//printings/ESLII_print10.pdf).

### 2.1. Split with stratification

[Stratification](https://en.wikipedia.org/wiki/Stratified_sampling) ensures that the class distributions (ratio of "good" to "bad" materials) are the same in the training and test set.

 $\color{DarkBlue}{\textsf{Short question}}$

- Why is this important? What could happen if we would not do this? 
 



 Stratification keeps roughly the same proportion of high- and low-uptake materials in the training and test sets. Without it, a random split could put too few high-performing materials in one set, especially if they are rare. The model would then have fewer examples of those materials to learn from, or the test score might not reflect how well it predicts them. 


For stratification to work, we to define what makes a "good" or a "bad" material. We will use 15 mmol CO$_2$ / g as the threshold for the uptake, thus binarizing our continuous target variable. (You can choose it based on the histogram of the variables).



 $\color{DarkBlue}{\textsf{Short Exercise}}$
 - add a column 'target_binary' that encodes whether a material is low performing (`0`) or high perfoming (`1`) by comparing the uptake with the `THRESHOLD`

<details>
<summary> <font color='green'>Click here for a hint</font></summary>
<ul>
    <li> you can use <a href='https://pandas.pydata.org/pandas-docs/stable/reference/api/pandas.cut.html'>pd.cut</a>, 
    <a href='https://stackoverflow.com/questions/4406389/if-else-in-a-list-comprehension'>list comprehension</a>, the <a href='https://scikit-learn.org/stable/modules/generated/sklearn.preprocessing.Binarizer.html#sklearn.preprocessing.Binarizer'> binarizer in sklearn </a>...) </li>
    <li> a list comprehension example: <code> [1 if value > THRESHOLD else 0 for value in df[TARGET]] </code> </li>
</ul>
</details>

In [8]:
THRESHOLD = 15 # in units of mmol CO2/g
df[TARGET_BINARY] = [1 if value > THRESHOLD else 0 for value in df[TARGET]] 

Now, we can perform the actual split into training and test set.

 $\color{DarkBlue}{\textsf{Short Exercise}}$
- select reasonable values for `XX` and `XY` and then perform the test/train splits. What do you consider when making this decision (think about what you would do with really small and really big datasets, what happens if you have only one test point, what happens to the model performance if you have more test points than training points)? 
- why do we need to perform the split into a training and test set? 
- would we use the test set to tune the hyperparameters of our model?

<details>
<summary> <font color='green'>Click here for a hint</font></summary>
<ul>
    <li>The `size` arguments can either be integers or, often more convenient, decimals like 0.1</li>
    <li>When you perform the split into training and test set you need to trade-off bias (pessimistic bias due to little training data) and variance (due to little test data) </li>
    <li>A typical split cloud be 70/30, but for huge dataset the test set might be too big and for small datasets the training set might be too small in this way </li>
</ul>
</details>



In [9]:
df_train_stratified, df_test_stratified = train_test_split(
    df,
    train_size=0.8,
    test_size=0.2,
    random_state=RANDOM_SEED,
    stratify=df[TARGET_BINARY],
)


 With a very small dataset, we would want to keep as much training data as possible and use cross-validation to help compare models. With a very large dataset, a smaller test fraction could still provide enough examples for a reliable evaluation. That is why we chose 80% for training and 20% for testing. This leaves most of the data for learning while still giving us a fairly large test set. A single test point would give a very unstable estimate of performance. Using more points for testing than training could make the model worse because it has fewer examples to learn from.

We keep a separate test set to check how well the model predicts materials it has not seen during training. Training errors alone can be misleading because a model can fit the training data well without generalizing. We should not tune hyperparameters on the test set: that would make our choices depend on it and could give an overly optimistic score. Instead, we tune using cross-validation within the training set and reserve the test set for evaluation.


## 3. Exploratory data analysis (EDA) 

After we have put the test set aside, we can give the training set a closer look.

### 3.1. Correlations

 $\color{DarkBlue}{\textsf{Short Exercise}}$
- Plot some features against the target property and calculate the Pearson and Spearman correlation coefficient (what is the different between those correlation coefficients?) 
- What are the strongest correlations? Did you expect them? 
- What can be a problem when features are correlated?
- *Optional:* Do they change if you switch from CO$_2$ to CH$_4$ uptake as the target instead? Explain your observation.



To get the correlation matrices, you can use the `df.corr(method=)`method on your dataframe (`df`). You might want to calculate not the full correlation matrix but just the correlation of the features with the targets

<details>
<summary> <font color='green'>Click here for a hint</font></summary>
<ul>
    <li> To get the correlation with a target, you can use indexing. E.g. <code>df.corr(method='spearman')[TARGET]</code></li>
    <li> use <code>.sort_values()</code> method on the output of `df.corr()` to sort by the value of the correlation coefficient  </li>
      <li> You can use something like <code>scatter = hv.Scatter(df, 'Di', [TARGET,  'density [g/cm^3]']).opts(color='density [g/cm^3]', cmap='rainbow')</code> for plotting. Also consider the <a href="https://holoviews.org/reference/elements/matplotlib/Scatter.html"> <code>holoviews</code> documentation</a>. In case <code>holoviews</code> is too new for you, you can of course just use <code>matplotlib</code> and something like <code>plt.scatter(x,y)</code> </li>
</ul>
</details>

In [36]:
# Explore four geometric features using only the training set.
plot_features = {
    "density [g/cm^3]": "Density (g/cm³)",
    "Di": "Largest included sphere diameter (Å)",
    "total_SA_gravimetric": "Gravimetric surface area (m²/g)",
    "total_POV_gravimetric": "Gravimetric pore volume (cm³/g)",
}

correlation_data = df_train_stratified[list(plot_features) + [TARGET]]
correlations = pd.DataFrame({
    "Pearson": correlation_data.corr(method="pearson")[TARGET].loc[list(plot_features)],
    "Spearman": correlation_data.corr(method="spearman")[TARGET].loc[list(plot_features)],
})

fig = make_subplots(
    rows=2, cols=2, shared_yaxes='all',
    horizontal_spacing=0.14, vertical_spacing=0.22,
    subplot_titles=[
        f"Pearson r = {correlations.loc[feature, 'Pearson']:.3f} | "
        f"Spearman ρ = {correlations.loc[feature, 'Spearman']:.3f}"
        for feature in plot_features
    ],
)
plot_colors = sample_colorscale('Magma', np.linspace(0.15, 0.75, len(plot_features)))
for index, ((feature, label), color) in enumerate(zip(plot_features.items(), plot_colors)):
    row, col = index // 2 + 1, index % 2 + 1
    fig.add_trace(go.Scatter(
        x=df_train_stratified[feature], y=df_train_stratified[TARGET],
        customdata=df_train_stratified['MOFname'],
        mode='markers', name=label,
        marker=dict(size=4, opacity=0.45, color=color),
        hovertemplate=(
            '%{customdata}<br>' + label + ': %{x:.3f}'
            '<br>CO₂ uptake: %{y:.3f} mmol/g<extra></extra>'
        ),
    ), row=row, col=col)
    fig.update_xaxes(title_text=label, row=row, col=col)
    fig.update_yaxes(title_text='CO₂ uptake (mmol/g)', row=row, col=col)

fig.update_layout(
    title='Geometric features vs CO₂ uptake — training set',
    template='plotly_white', height=800, showlegend=False,
    margin=dict(t=100, b=80),
)
fig.show(config=PLOT_CONFIG)

# Rank by absolute correlation so strong negative relationships also rank highly.
correlations.sort_values("Pearson", key=lambda values: values.abs(), ascending=False).round(3)


,Pearson,Spearman
total_SA_gravimetric,0.926,0.954
density [g/cm^3],-0.883,-0.949
total_POV_gravimetric,0.777,0.957
Di,0.758,0.849


 Pearson correlation measures how closely two variables follow a straight-line relationship. Spearman correlation measures whether one generally increases or decreases as the other increases, even when the relationship is not linear.

Among the four features plotted below, gravimetric surface area has the strongest Pearson correlation with uptake (0.926), followed by density (−0.883). For Spearman correlation, gravimetric pore volume is strongest (0.957), followed by gravimetric surface area (0.954) and density (−0.949). These trends make sense: more accessible surface and pore space per gram can allow more gas to be adsorbed, while denser materials tend to have less pore space per gram. One would therefore expect these geometric features to be useful for predicting high-pressure uptake. The higher Spearman than Pearson correlation for pore volume suggests that its relationship with uptake is more consistently increasing than strictly linear.

When input features are strongly correlated with each other, they carry overlapping information. This can make it difficult to tell which feature is responsible for a prediction, and in some models it can make fitted coefficients unstable. 

## 4. Baselines

For machine learning, it is important to have some *baselines* to which one then compares the results of a model. Think of a classification model for some rare disease where we only have 1% postives. A classification model that only predictes the negatives *all the time* will still have a amazingly high accuracy. To be able to understand if our model is really better than such a simple prediction we need to make the simple prediction first. This is what we call a baseline.

A baseline could be a really simple model, a basic heuristic or the current state of the art.
this. We will use a heuristic.

For this we use sklearn `Dummy` objects that simply calculate the mean, the median or the most frequent case of the training set, when you run the `fit()` method on them (which takes the features matrix $\mathbf{X}$ and the labels $\mathbf{y}$ as arguments.
This is, the prediction of a `DummyRegressor` with `mean` strategy will always be the mean, independent of the input (it will not look at the feature matrix!). 

Instead of using those `sklearn` objects you could also just manually compute the the mean or median of the dataset. But we will use those objects as we can learn in this way how to use estimators in `sklearn` and it is also allows you to test your full pipeline with different (baseline) models. 
What does this mean? In practice this means that you can use all the regression and classification models shown in the figure below in the same way, they will all have a `fit()` method that accepts `X` and `y` and a predict method that accepts `X` and returns the predictions. 


<img src="https://scikit-learn.org/1.3/_static/ml_map.png" alt="ML Map" width="800"/>

The estimator objects can be always used in the same way 

<img src="https://static.packt-cdn.com/products/9781789800265/graphics/d49a2e95-8f22-42ed-89f1-474b3d028787.png" alt="ML Map" width="400"/>

Using these objects, instead of the mean directly, allows you to easily swap them with other models in pipelines, where one chains many data transformation steps (see section 6).

### 4.1. Build dummy models

$\color{DarkBlue}{\textsf{Short Question}}$
- If you call `.fit(X, y)` on a `DummyRegressor` does it actually use the `X`? If not, why is there still the place for the `X` in the function? If yes, how does it use it?



 For the mean and median strategies, `DummyRegressor.fit(X, y)` does not use the feature values in `X` to learn a relationship. It only calculates a constant from the training targets `y`, then predicts that same value for every material. It still accepts `X` so that, apparently, it has the same interface as other scikit-learn models. 


$\color{DarkBlue}{\textsf{Short Exercise}}$
- Create [`DummyRegressor`](https://scikit-learn.org/stable/modules/generated/sklearn.dummy.DummyRegressor.html) instances for  `mean`, `median`. (e.g. `dummyinstance = DummyRegressor(strategy='mean')`)
- Train them on the training data (`dummyinstance.fit(df_train[FEATURES], df_train[TARGET])`)



<details>
<summary> <font color='green'>Click here for hints</font></summary>
<ul>
    <li> to create <code>DummyRegressor</code> you can for example use <code> dummyregressor_mean = DummyRegressor(strategy='mean') </code> </li>
    <li> to see the implementation of the <code>DummyRegressor</code> you can check out <a href="https://github.com/scikit-learn/scikit-learn/blob/73732e5a0bc9b72c7049dc699d69aaedbb70ef0a/sklearn/dummy.py#L391"> the source code on GitHub</a> </li>
</ul>
</details>

In [11]:
# Build DummyRegressors
dummyregressor_mean = DummyRegressor(strategy='mean')
dummyregressor_median = DummyRegressor(strategy='median')

In [12]:
# Fit Dummy Regressors
dummyregressor_mean.fit(df_train_stratified[FEATURES], df_train_stratified[TARGET])
dummyregressor_median.fit(df_train_stratified[FEATURES], df_train_stratified[TARGET])

# Show the constant uptake predicted by each baseline.
print(f"Mean baseline prediction: {dummyregressor_mean.constant_.item():.3f} mmol/g")
print(f"Median baseline prediction: {dummyregressor_median.constant_.item():.3f} mmol/g")


Mean baseline prediction: 11.798 mmol/g
Median baseline prediction: 10.385 mmol/g


#### Evaluate the performance of the dummy models

 $\color{DarkBlue}{\textsf{Short Exercise}}$
- Calculate maximum error, mean absolute error and mean square error for the dummy regressors on training and test set. What would you expect those numbers to be?
- Do the actual values surprise you? 
- What does this mean in practice for reporting of metrics/the reasoning behind using baseline models

It can be handy to store our metrics of choice in a nested dictionary ([Python dictionaries are key-value pairs](https://www.tutorialspoint.com/python/python_dictionary.htm)): 

```python
{
    'dummyestimator1': {
                        'metric_a_key': metric_a_value, 
                        'metric_b_key': metric_b_value
                    },
    'dummyestimator2': {
                        'metric_a_key': metric_a_value, 
                        'metric_b_key': metric_b_value
                    },
 }
``` 

You will now write functions `get_regression_metrics(model, X, y_true)` that compute the metrics and return this dictionary for a given model. The `predict` method takes the feature matrix $\mathbf{X}$ as input.

In them, we calculate 

$\mathrm {MAE} =\frac{\sum _{i=1}^{n}\left|Y_{i}-\hat{y}_{i}\right|}{n}.$

and 

$\mathrm {MSE} = {\frac {1}{n}}\sum _{i=1}^{n}(Y_{i}-{\hat {Y_{i}}})^{2}.$ 

where $\hat{y}$ are the predictions and, $Y_{i}$ the true values.

as well as the maximum error.



<details>
<summary> <font color='green'>Click here for hints</font></summary>
<ul>
    <li> to perform a prediction using a estimator object, you can call <code> classifier.predict(X) </code> </li>
    <li> to calculate metrics, you can for example call <code>accuracy_score(true_values, predicted_values) </code> </li>
</ul>
</details>

In [13]:
def get_regression_metrics(model, X, y_true):
    """
    Get a dicionary with regression metrics:

    model: sklearn model with predict method
    X: feature matrix
    y_true: ground truth labels
    """
    y_predicted = model.predict(X)

    mae = mean_absolute_error(y_true, y_predicted)
    mse = mean_squared_error(y_true, y_predicted)
    maximum_error = max_error(y_true, y_predicted)

    metrics_dict = {
        'mae': mae,
        'mse': mse,
        'max_error': maximum_error
    }

    return metrics_dict

In [14]:
dummy_regressors = [
    ('mean', dummyregressor_mean),
    ('median', dummyregressor_median)
]

In [15]:
dummy_regressor_results_test = {} # initialize empty dictionary
dummy_regressor_results_train = {}

# loop over the dummy_regressor list
# if you have a tuple regressorname, regressor = (a, b) that is automatically expanded into the variables
# a = regressorname, b = regressor
for regressorname, regressor in dummy_regressors:
    print(f"Calculating metrics for {regressorname}")
    dummy_regressor_results_test[regressorname] = get_regression_metrics(regressor, df_test_stratified[FEATURES], df_test_stratified[TARGET])
    dummy_regressor_results_train[regressorname] = get_regression_metrics(regressor, df_train_stratified[FEATURES], df_train_stratified[TARGET])

print("Baseline errors (MAE and max_error in mmol/g; MSE in (mmol/g)^2):")
pp.pprint({
    'train': dummy_regressor_results_train,
    'test': dummy_regressor_results_test,
})


Calculating metrics for mean
Calculating metrics for median
Baseline errors (MAE and max_error in mmol/g; MSE in (mmol/g)^2):
{'test': {'mean': {'mae': 6.23570655480622,
                   'max_error': 20.950406086755144,
                   'mse': 52.37955580408542},
          'median': {'mae': 6.15904320182382,
                     'max_error': 22.364281338299996,
                     'mse': 54.20248538065805}},
 'train': {'mean': {'mae': 6.333027169434022,
                    'max_error': 22.69371401465515,
                    'mse': 54.358316750106916},
           'median': {'mae': 6.256700923073538,
                      'max_error': 24.1075892662,
                      'mse': 56.35735997703791}}}


We would expect the dummy models to have fairly large errors because they give the same prediction to every material, even though the uptake varies considerably. Their training and test errors should be reasonably similar if the two sets have similar uptake distributions, since these models cannot memorize individual materials. The mean gives the smallest training MSE among constant predictions, while the median gives the smallest training MAE. Neither is chosen to minimize the maximum error.

The test results are: the mean baseline has an MAE of 6.236 mmol/g and an MSE of 52.380 (mmol/g)², while the median baseline has an MAE of 6.159 mmol/g and an MSE of 54.202 (mmol/g)². Their maximum test errors are 20.950 mmol/g and 22.364 mmol/g, respectively. This is not surprising, because a constant prediction misses the extremes of the uptake distribution, and the strategy that is better for MAE is not necessarily better for MSE.

These results show why a model's error should be reported alongside a baseline on the same test set. A score only tells us something useful if we know how much better it is than a simple prediction. We should also report more than one metric: MAE describes the average absolute error, MSE gives more weight to large errors, and maximum error shows the worst case in that set.


## 5. Build actual regression models

Let's build a simple [kernel ridge regression (KRR)](https://emtiyaz.github.io/pcml15/kernel-ridge-regression.pdf) machine learning model and train it with our raw data.
You can try different kernels, but we recommend to start with the Gaussian radial basis function ('rbf') kernel.
 
 $\color{DarkBlue}{\textsf{Short Question}}$
- Do you expect this model to perform better than the dummy models?
- Train it and then calculate the performance metrics on the training and test set. How do they compare to the performance of the dummy models?
- What is the shape of the Kernel and of the weights? (you can check your answer by looking at the `dual_coef_` attribute of the KRR instance. You can get shapes of objects using the `shape` atrribute 

In [16]:
# Train the model with a Gaussian kernel
krr = KernelRidge(kernel='rbf')
krr.fit(df_train_stratified[FEATURES], df_train_stratified[TARGET])

,"kernel kernel: str or callable, default=""linear""Kernel mapping used internally. This parameter is directly passed to:class:`~sklearn.metrics.pairwise.pairwise_kernels`.If `kernel` is a string, it must be one of the metricsin `pairwise.PAIRWISE_KERNEL_FUNCTIONS` or ""precomputed"".If `kernel` is ""precomputed"", X is assumed to be a kernel matrix.Alternatively, if `kernel` is a callable function, it is called oneach pair of instances (rows) and the resulting value recorded. Thecallable should take two rows from X as input and return thecorresponding kernel value as a single number. This means thatcallables from :mod:`sklearn.metrics.pairwise` are not allowed, asthey operate on matrices, not single samples. Use the stringidentifying the kernel instead.",'rbf'
,"alpha alpha: float or array-like of shape (n_targets,), default=1.0Regularization strength; must be a positive float. Regularizationimproves the conditioning of the problem and reduces the variance ofthe estimates. Larger values specify stronger regularization.Alpha corresponds to ``1 / (2C)`` in other linear models such as:class:`~sklearn.linear_model.LogisticRegression` or:class:`~sklearn.svm.LinearSVC`. If an array is passed, penalties areassumed to be specific to the targets. Hence they must correspond innumber. See :ref:`ridge_regression` for formula.",1
,"gamma gamma: float, default=NoneGamma parameter for the RBF, laplacian, polynomial, exponential chi2and sigmoid kernels. Interpretation of the default value is left tothe kernel; see the documentation for sklearn.metrics.pairwise.Ignored by other kernels.",None
,"degree degree: float, default=3Degree of the polynomial kernel. Ignored by other kernels.",3
,"coef0 coef0: float, default=1Zero coefficient for polynomial and sigmoid kernels.Ignored by other kernels.",1
,"kernel_params kernel_params: dict, default=NoneAdditional parameters (keyword arguments) for kernel function passedas callable object.",None
Name,Type,Value
"X_fit_ X_fit_: {ndarray, sparse matrix} of shape (n_samples, n_features)Training data, which is also required for prediction. Ifkernel == ""precomputed"" this is instead the precomputedtraining matrix, of shape (n_samples, n_samples).","ndarray[float64](13903, 164)","[[ 15.87, 10.5 , 15.84,..., 27.84, 25.92, 53.76], [ 3.96, 2.37, 3.93,..., 11.76, 7.2 , 15.04], [ 13.78, 10.43, 13.78,..., 5.76, 6.48, 13.44], ..., [ 5.48, 4.2 , 5.48,..., 16.2 , 12. , 37.92], [ 21.55, 11.82, 21.55,..., 37.12, 25.92,109.44], [ 5.06, 3.4 , 4.27,..., 5.76, 7.32, 10.84]]"
"dual_coef_ dual_coef_: ndarray of shape (n_samples,) or (n_samples, n_targets)Representation of weight vector(s) in kernel space","ndarray[float64](13903,)","[10.21, 2.31, 8.75,..., 3.57,10.59, 3.45]"
"feature_names_in_ feature_names_in_: ndarray of shape (`n_features_in_`,)Names of features seen during :term:`fit`. Defined only when `X`has feature names that are all strings... versionadded:: 1.0","ndarray[object](164,)","['Di','Df','Dif',...,'sum-D_mc_CRY-S-1-all','sum-D_mc_CRY-S-2-all', 'sum-D_mc_CRY-S-3-all']"
n_features_in_ n_features_in_: intNumber of features seen during :term:`fit`... versionadded:: 0.24,int,164


In [17]:
# get the metrics on the train and the test set using the get_regression_metrics functions (as above)
krr_results_train = get_regression_metrics(krr, df_train_stratified[FEATURES], df_train_stratified[TARGET])
krr_results_test = get_regression_metrics(krr, df_test_stratified[FEATURES], df_test_stratified[TARGET])

pp.pprint({'train': krr_results_train, 'test': krr_results_test})

# The training kernel has one row and one column per training material.
print("Training kernel shape:", (krr.X_fit_.shape[0], krr.X_fit_.shape[0]))
print("Weights shape:", krr.dual_coef_.shape)


{'test': {'mae': 11.700920671067307,
          'max_error': 32.748804214699994,
          'mse': 189.50792511510778},
 'train': {'mae': 5.884340430149515,
           'max_error': 17.246056071300004,
           'mse': 48.25742808663033}}
Training kernel shape: (13903, 13903)
Weights shape: (13903,)




KRR can use the descriptors to learn relationships with uptake, so it has the potential to outperform the constant dummy predictions. However, this first model uses default hyperparameters, so a better test performance is not guaranteed.

The raw-feature KRR has training MAE 5.884 mmol/g and test MAE 11.701 mmol/g. The test dummy MAEs are 6.236 mmol/g (mean) and 6.159 mmol/g (median). Its test MSE is 189.508 (mmol/g)², compared with 52.380 and 54.202 for the mean and median baselines. Its test maximum error is 32.749 mmol/g, compared with 20.950 and 22.364.

The training errors are lower than those of both dummy baselines, but all three test errors are higher. This first KRR therefore generalizes poorly. RBF similarities depend on distances between feature vectors; unscaled descriptors with large numerical ranges can dominate those distances.

The training kernel matrix has shape (13903, 13903), since it contains a similarity for every pair of training materials. The weights (`dual_coef_`) have shape (13903,): one coefficient per training material for this single target.


## 6. Evaluate the model performance in detail

We have trained our first machine learning model!
We'll first have a closer look at its performance, before learning how to improve it.

 $\color{DarkBlue}{\textsf{Short Exercise}}$
- Create a parity plot (true values against predictions)for the training and test data
- Plot a histogram of the distribution of the training and test errors on the training and test set. Plot the errors also as a function of the true value
- Let's assume we would like to use our model for pre-screening a library of millions of porous materials to zoom-in on those with the most promising gas uptake. Could you tolerate the errors of your model?
- Compare the parity plots for this model with the ones for the dummy models. 
Use the plotting functions below the evaluate all the following models you train.

For this exercise, it can be handy to save the results in a dictionary, e.g. 
```(python)
res_train = {
    'y true': [],
    'y pred': []
}
```

<details>
<summary> <font color='green'>Click here for hints for plotting</font></summary>
<ul>
    <li> If you want to use matplotlib to make the parity plots, you can use the <a href="https://matplotlib.org/3.1.1/api/_as_gen/matplotlib.pyplot.hist2d.html">hist2d function</a> </li>
    <li> To create the frequencies and the edges of a histogram, one can use <code>np.histogram</code></li>
</ul>
</details>

In [18]:
# Create dictionaries with training and test results to create parity plots
res_train = {
    'y true': df_train_stratified[TARGET],
    'y pred': krr.predict(df_train_stratified[FEATURES])
}

res_test = {
    'y true': df_test_stratified[TARGET],
    'y pred': krr.predict(df_test_stratified[FEATURES])
}

Now, lets calculate the errors

In [19]:
res_train["error"] = res_train["y true"] - res_train["y pred"]
res_test["error"] = res_test["y true"] - res_test["y pred"]


Now, plot the parity plots and error distributions

<details>
<summary> <font color='green'>Click here for hints for plotting</font></summary>
If you want interactive plots, you can use the following code:
<pre><code>
hv.extension("bokeh")
hex_train = hv.HexTiles(res_train, ["y true", "y pred"]).hist(
    dimension=["y true", "y pred"]
)
hex_test = hv.HexTiles(res_test, ["y true", "y pred"]).hist(
    dimension=["y true", "y pred"]
)
hex_train + hex_test
</code>
</details>

In [20]:
def plot_regression_results(res_train, res_test, model_name):
    fig = make_subplots(
        rows=2, cols=3, shared_xaxes='columns', shared_yaxes='columns',
        horizontal_spacing=0.10, vertical_spacing=0.20,
        subplot_titles=[
            f'{split}: {title}'
            for split in ['Training', 'Test']
            for title in ['parity plot', 'error distribution', 'error vs true uptake']
        ],
    )
    parity_values = np.concatenate([
        res_train['y true'], res_train['y pred'],
        res_test['y true'], res_test['y pred']
    ])
    limits = [float(parity_values.min()), float(parity_values.max())]
    if limits[0] == limits[1]:
        limits = [limits[0] - 0.5, limits[1] + 0.5]
    error_bins = np.histogram_bin_edges(
        np.concatenate([res_train['error'], res_test['error']]), bins=40
    )
    reference_line = dict(color=sample_colorscale('Magma', [0.05])[0], dash='dash', width=1)

    for row, ((split, results), color) in enumerate(zip(
        [('Training', res_train), ('Test', res_test)], MAGMA_COLORS
    ), start=1):
        marker = dict(size=4, opacity=0.45, color=color)
        fig.add_trace(go.Scatter(
            x=results['y true'], y=results['y pred'], mode='markers',
            name=split, marker=marker,
            hovertemplate='True: %{x:.3f} mmol/g<br>Predicted: %{y:.3f} mmol/g<extra>%{fullData.name}</extra>',
        ), row=row, col=1)
        fig.add_trace(go.Scatter(
            x=limits, y=limits, mode='lines', line=reference_line,
            hoverinfo='skip', showlegend=False,
        ), row=row, col=1)
        fig.update_xaxes(title_text='True CO₂ uptake (mmol/g)', range=limits,
                         constrain='domain', row=row, col=1)
        # The two parity plots share axes; anchor their common y scale to x.
        fig.update_yaxes(title_text='Predicted CO₂ uptake (mmol/g)', range=limits,
                         row=row, col=1)

        # Keep the same bin edges and probability-density normalization on both splits.
        density, edges = np.histogram(results['error'], bins=error_bins, density=True)
        fig.add_trace(go.Bar(
            x=(edges[:-1] + edges[1:]) / 2, y=density, width=np.diff(edges),
            customdata=np.column_stack([edges[:-1], edges[1:]]),
            name=split, marker_color=color, opacity=0.8,
            hovertemplate=(
                'Error bin: %{customdata[0]:.3f} to %{customdata[1]:.3f} mmol/g'
                '<br>Probability density: %{y:.4f}<extra>%{fullData.name}</extra>'
            ),
        ), row=row, col=2)
        fig.add_vline(x=0, line=reference_line, row=row, col=2)
        fig.update_xaxes(title_text='Error: true − predicted (mmol/g)', row=row, col=2)
        fig.update_yaxes(title_text='Probability density', row=row, col=2)

        fig.add_trace(go.Scatter(
            x=results['y true'], y=results['error'], mode='markers',
            name=split, marker=marker,
            hovertemplate='True: %{x:.3f} mmol/g<br>Error: %{y:.3f} mmol/g<extra>%{fullData.name}</extra>',
        ), row=row, col=3)
        fig.add_hline(y=0, line=reference_line, row=row, col=3)
        fig.update_xaxes(title_text='True CO₂ uptake (mmol/g)', row=row, col=3)
        fig.update_yaxes(title_text='Error: true − predicted (mmol/g)', row=row, col=3)

    fig.update_layout(
        title=model_name, template='plotly_white', height=800,
        showlegend=False, bargap=0, margin=dict(t=100, b=80),
        yaxis4=dict(scaleanchor='x4', scaleratio=1, constrain='domain'),
    )
    fig.show(config=PLOT_CONFIG)


plot_regression_results(res_train, res_test, 'KRR — unscaled features')


In [21]:
# Compare with both dummy models 
for regressorname, regressor in dummy_regressors:
    dummy_res_train = {
        'y true': df_train_stratified[TARGET],
        'y pred': regressor.predict(df_train_stratified[FEATURES])
    }
    dummy_res_test = {
        'y true': df_test_stratified[TARGET],
        'y pred': regressor.predict(df_test_stratified[FEATURES])
    }
    dummy_res_train['error'] = dummy_res_train['y true'] - dummy_res_train['y pred']
    dummy_res_test['error'] = dummy_res_test['y true'] - dummy_res_test['y pred']
    plot_regression_results(dummy_res_train, dummy_res_test,
                            f'Dummy regressor — {regressorname}')

The diagonal in the parity plots represents perfect predictions. The dummy models predict the training mean or median for every material, so their parity plots are horizontal lines. Their errors (true − predicted) increase linearly with true uptake: they overestimate low-uptake materials and underestimate high-uptake materials. Positive errors indicate underprediction.

The metrics reported in Section 5 show that the unscaled KRR fits the training data better than the dummy models but performs worse on the test set. The parity plots and error distributions let us examine this gap and check whether errors are concentrated among the high-uptake materials we want to identify.

We would not consider this model reliable for pre-screening millions of materials in its current form. Its reported test MAE is about 11.7 mmol/g, compared with about 6.2 mmol/g for the dummy models and the 15 mmol/g threshold used to identify high-performing materials. Errors on this scale could discard promising candidates or select poor ones for expensive follow-up simulations. The dummy models also cannot rank candidates because their predictions are constant. 

## 7. Improve the model 

Our training set still has a couple of issues you might have noticed:
- The feature values are not scaled (different features are measured in different units ...)
- Some features are basically constant, i.e. do not contain relevant information and just increase the dimensionality of the problem 
- Some feature distributions are skewed (which is more relevant for some models than for others ...)

$\color{DarkBlue}{\textsf{Short Question}}$
- Why might the scaling of the features be relevant for a machine learning model? 



Scaling matters because the RBF kernel depends on squared distances between feature vectors. Without scaling, descriptors with large numerical ranges can dominate those distances. Standard scaling gives each nonconstant feature unit variance.

### 7.1. Standard scaling and building a first pipeline 

Given that we will now go beyond training a single model, we will build [Pipelines](https://scikit-learn.org/stable/modules/generated/sklearn.pipeline.Pipeline.html), which are objects that can collect a selection of transformations and estimators. This makes it quite easy to apply the same set of operations to different datasets. A simple pipeline might be built as follows 

<img src="https://vitalflux.com/wp-content/uploads/2020/08/ML-Pipeline-Page-2-1024x307.png" alt="Pipeline" width="800"/>



 $\color{DarkBlue}{\textsf{Short Exercise}}$
- Build a pipline that first performs standard scaling and then fits a KRR. Call it `pipe_w_scaling`. 
- Fit it on the training set 
- Make predictions, calculate the errors and make the parity plots

<details>
<summary> <font color='green'>Click here for hints</font></summary>
<ul>
    <li> the <code>fit</code>, <code>predict</code> methods also work for pipelines </li>
</ul>
</details>

In [22]:
X_train = df_train_stratified[FEATURES]
y_train = df_train_stratified[TARGET]
X_test = df_test_stratified[FEATURES]
y_test = df_test_stratified[TARGET]


def evaluate_regression_model(model, model_name):
    # Reuse the metrics from Section 4 and the plots from Section 6.
    results = {}
    metrics = {}
    for split, X, y in [('train', X_train, y_train), ('test', X_test, y_test)]:
        results[split] = {'y true': y, 'y pred': model.predict(X)}
        results[split]['error'] = y - results[split]['y pred']
        metrics[split] = get_regression_metrics(model, X, y)
    print(model_name)
    pp.pprint(metrics)
    plot_regression_results(results['train'], results['test'], model_name)
    return metrics


pipe_w_scaling = Pipeline(
    [
        ('scaling', StandardScaler()),
        ('krr', KernelRidge(kernel='rbf'))
    ]
)
pipe_w_scaling.fit(X_train, y_train)
scaled_results = evaluate_regression_model(pipe_w_scaling, 'KRR — standard scaling')


KRR — standard scaling
{'test': {'mae': 1.0293600401789056,
          'max_error': 13.50923550505269,
          'mse': 2.5724028218282893},
 'train': {'mae': 0.9854615289459429,
           'max_error': 13.237423995796757,
           'mse': 2.224057933774228}}


### 7.2. Hyperparameter optimization

A key component we did not optimize so far are hyperparameters. Those are parameters of the model that we usually cannot learn from the data but have to fix before we train the model. 
Since we cannot learn those parameters it is not trivial to select them. Hence, what we typically do in practice is to create another set, a "validation set", and use it to test models trained with different hyperparameters.

The most common approach to hyperparameter optimization is to define a grid of all relevant parameters and to search over the grid for the best model performance.

$\color{DarkBlue}{\textsf{Short Exercise}}$
- Think about which parameters you could optimize in the pipeline. Note that your KRR model has two parameters you can optimize. You can also switch off some steps by setting them to `None'.
- For each parameter you need to define a resonable grid to search over.
- Recall, what k-fold cross-validation does. Run the hyperparameter optimization using 5-fold cross-validation (you can adjust the number of folds according to your computational resources/impatience. It turns out at k=10 is the [best tradeoff between variance and bias](https://arxiv.org/abs/1811.12808)). 
Tune the hyperparameters until you are statisfied (e.g., until you cannot improve the cross validated error any more)
- Why don't we use the test set for hyperparameter tuning but instead test on the validation set? 
- Evaluate the model performance by calculating the performance metrics (MAE, MSE, max error) on the training and the test set.
- *Optional:* Instead of grid search, try to use random search on the same grid (`RandomizedSearchCV`) and fix the number of evaluations (`n_iter`) to a fraction of the number of evaluations of grid search. What do you observe and conclude?



 $\color{DarkRed}{\textsf{Tips}}$
- If you want to see what is happening, set the `verbosity` argument of the `GridSearchCV` object to a higher number.
 
- If you want to speed up the optimization, you can run it in parallel by setting the `n_jobs` argument to the number of workers. If you set it to -1 it will use all available cores. *Using all cores might freeze your computer if you do not have enough memory*
 
- If the optimization is too slow, reduce the number of data points in your set, the number of folds or the grid size. Note that it can also be a feasible strategy to first use a coarser grid and the a finer grid for fine-tuning.

- For grid search, you need to define a parameter grid, which is a dictionary of the following form: 
```(python)
param_grid = {
                    'pipelinestage__parameter': np.logspace(-4,1,10),
                    'pipelinestage': [None, TransformerA(), TransformerB()]
            }
```

- After the search, you can access the best model with `.best_estimator_` and the best parameters with `.best_params_` on the GridSearchCV instance. For example `grid_krr.best_estimator_`

- If you initialize the GridSearchCV instance with `refit=True` it will automatically train the model with all training data (and not only the training folds from cross-validations)

The double underscore (dunder) notation works recursively and specifies the parameters for any pipeline stage. 
For example, `ovasvm__estimator__cls__C` would specifiy the `C` parameter of the estimator in the one-versus-rest classifier `ovasvm`. 

You can print all parameters of the pipeline using `print(sorted(pipeline.get_params().keys()))`

<div class="alert alert-block alert-warning">
Be aware that tight grids will drastically increase the number of experiments you will run! In some cases, it can be useful to perform the optimization in steps, i.e., first use a coarse grid and then refine in interesting regions. 
Alternatively, there are approached like <a href="https://www.jmlr.org/papers/volume18/16-558/16-558.pdf"> hyperband <a> that dynamically adjust the number of data points.
</div>

<details>
<summary> <font color='green'>Click here for hints about pipelines and grid search</font></summary>
<ul>
    <li> You can use the <code>np.logspace</code> function to generate a grid for values that you want to vary on a logarithmic scale </li>
    <li> There are two hyperparameters for KRR: the regularization strength <code>alpha</code> and the Gaussian width  <code>gamma</code> </li>
    <li> For the regularization strength, values between 1 and 1e-3 can be reasonable. For gamma you can use the median heuristic, gamma = 1 / median, or values between 1e-3 and 1e3</li>
</ul>
</details>

In [23]:
# Use the same folds and scoring for every search so CV scores are comparable.
from sklearn.model_selection import KFold
from sklearn.base import clone

cv = KFold(n_splits=5, shuffle=True, random_state=RANDOM_SEED)
param_grid = {
    'scaling': [MinMaxScaler(), StandardScaler()],
    'krr__alpha': np.logspace(-3, 1, 3),
    'krr__gamma': np.logspace(-4, 0, 3)
}

grid_krr = GridSearchCV(
    pipe_w_scaling, param_grid=param_grid, scoring='neg_mean_absolute_error',
    cv=cv, refit=True, verbose=2, n_jobs=20, pre_dispatch=20
)

# Optional comparison: 6 candidates instead of the coarse grid's 18.
random_krr = RandomizedSearchCV(
    pipe_w_scaling, param_distributions=param_grid, n_iter=6,
    scoring='neg_mean_absolute_error', cv=cv, refit=True,
    random_state=RANDOM_SEED, verbose=2, n_jobs=20, pre_dispatch=20
)


In [24]:
# Fit only on training data; each search refits its best pipeline automatically.
grid_krr.fit(X_train, y_train)
coarse_grid_krr = grid_krr

# Refine alpha and gamma around the coarse optimum, retaining its scaler.
refined_param_grid = {
    'scaling': [clone(coarse_grid_krr.best_params_['scaling'])],
    'krr__alpha': coarse_grid_krr.best_params_['krr__alpha'] * np.logspace(-0.5, 0.5, 3),
    'krr__gamma': coarse_grid_krr.best_params_['krr__gamma'] * np.logspace(-0.5, 0.5, 3)
}
refined_grid_krr = GridSearchCV(
    pipe_w_scaling, param_grid=refined_param_grid,
    scoring='neg_mean_absolute_error', cv=cv, refit=True,
    verbose=2, n_jobs=20, pre_dispatch=20
)
refined_grid_krr.fit(X_train, y_train)
grid_krr = max([coarse_grid_krr, refined_grid_krr], key=lambda search: search.best_score_)
random_krr.fit(X_train, y_train)

for name, search in [('Coarse grid', coarse_grid_krr),
                     ('Refined grid', refined_grid_krr), ('Random search', random_krr)]:
    print(f'{name}: best CV MAE = {-search.best_score_:.3f} mmol/g')
    pp.pprint(search.best_params_)


Fitting 5 folds for each of 18 candidates, totalling 90 fits


[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=MinMaxScaler(); total time=  17.3s
[CV] END krr__alpha=0.001, krr__gamma=0.01, scaling=MinMaxScaler(); total time=  18.0s
[CV] END krr__alpha=0.001, krr__gamma=0.01, scaling=MinMaxScaler(); total time=  18.0s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=StandardScaler(); total time=  18.8s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=MinMaxScaler(); total time=  24.0s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=StandardScaler(); total time=  23.6s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=StandardScaler(); total time=  23.9s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=StandardScaler(); total time=  24.4s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=MinMaxScaler(); total time=  24.9s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=StandardScaler(); total time=  25.9s
[CV] END krr__alpha=0.001, krr__gamma=0.01, scaling=MinMaxScaler(); total time=  26.1s
[CV] END krr__alp

In [25]:
grid_results = evaluate_regression_model(grid_krr.best_estimator_, 'KRR — grid search')
random_results = evaluate_regression_model(random_krr.best_estimator_, 'KRR — random search')


KRR — grid search
{'test': {'mae': 0.6481550870864936,
          'max_error': 9.060679554162338,
          'mse': 0.9874854754947653},
 'train': {'mae': 0.47858480030766154,
           'max_error': 5.7959650524328215,
           'mse': 0.4995644160217441}}


KRR — random search
{'test': {'mae': 0.6706087207137602,
          'max_error': 11.133048454387726,
          'mse': 1.1856204118986318},
 'train': {'mae': 0.33226051483575986,
           'max_error': 4.848348377008797,
           'mse': 0.25952883581956737}}


We optimize the regularization strength `alpha`, the RBF distance parameter `gamma`, and the scaling method. The logarithmic grids cover several orders of magnitude, followed by a finer search around the best pair. In five-fold cross-validation, each training fold is held out once while the other four are used to fit the whole pipeline. We select the lowest mean validation MAE (`neg_mean_absolute_error` is maximized by scikit-learn). The test set is reserved for evaluation: using it to choose hyperparameters would make its error an optimistic estimate of generalization. Random search below evaluates one third of the coarse-grid candidates; its printed CV MAE shows the accuracy/cost tradeoff for this run.


<details>
<summary> <font color='green'>Click here for some more information about hyperparameter optimization</font></summary>
Grid search is not the most efficient way to perform hyperparamter optimization. Even <a href="http://jmlr.csail.mit.edu/papers/volume13/bergstra12a/bergstra12a.pdf">random search was shown to be more efficient</a>. Really efficient though are Bayesian optimization approaches like <a href='https://papers.nips.cc/paper/4443-algorithms-for-hyper-parameter-optimization.pdf)'>TPE</a>. This is implemented in the hyperopt library, which is also installed in your conda environment.
</details>

<details>
<summary> <font color='green'>Click here for hyperparameter optimization with hyperopt (advanded and optional outlook)</font></summary>
    
<b>Import the tools we need</b>
<code>
from hyperopt import fmin, tpe, hp, STATUS_OK, Trials, mix, rand, anneal, space_eval
from functools import partial
</code>    

<b>Define the grid</b>
<code>
param_hyperopt = {
    "krr__alpha": hp.loguniform("krr__alpha", np.log(0.001), np.log(10)),
    "krr__gamma": hp.loguniform("krr__gamma", np.log(0.001), np.log(10)),
}
</code> 

<b>Define the objective function</b>
<code>
def objective_function(params):
    pipe.set_params(
        **{
            "krr__alpha": params["krr__alpha"],
            "krr__gamma": params["krr__gamma"],
        }
    )
    score = cross_val_score(
        pipe, X_train, y_train, cv=10, scoring="neg_mean_absolute_error"
    ).mean()
    return {"loss": -score, "status": STATUS_OK} 
</code>

<b>We will use a search in which we mix random search, annealing and tpe</b>
<code>
trials = Trials()
mix_search = partial(
   mix.suggest,
   p_suggest=[(0.15, rand.suggest), (0.15, anneal.suggest), (0.7, tpe.suggest)],
)
</code>

<b>Now, we can minimize the objective function.</b>
<code>
best_param = fmin(
        objective_function,
        param_hyperopt,
        algo=mix_search,
        max_evals=MAX_EVALES,
        trials=trials,
        rstate=np.random.RandomState(RANDOM_SEED),
    )
</code>

</details>

## 8. Feature Engineering 

Finally, we would like to remove features with low variance. This can be done by setting a variance threshold.

$\color{DarkBlue}{\textsf{Short Question}}$
    
- What is the reasoning behind doing this? 
- When might it go wrong and why?



Removing constant features reduces computation without losing information that varies across the training materials. Removing nearly constant features may also reduce noise. However, small variance does not imply small predictive value: a rare functional group could be important for adsorption. Variance depends on units, so a single threshold on raw descriptors must be used cautiously. Here the filter is fitted inside each training fold before scaling, and its threshold is tuned by validation MAE. A threshold of zero removes only constant columns.


 $\color{DarkBlue}{\textsf{Short Exercise}}$
- Add a variance threshold to the pipeline (select the correct function argument)
- Use random search for hyperparameter optimization, retrain the pipeline, and calculate the performance metrics (max error, MAE, MSE) on the training and test set

In [26]:
# Keep feature selection inside the pipeline to avoid validation leakage.
pipe_variance_threshold = Pipeline(
    [
        ('variance_treshold', VarianceThreshold(threshold=0.0)),
        ('scaling', StandardScaler()),
        ('krr', KernelRidge(kernel='rbf'))
    ]
)


In [27]:
param_grid_variance_threshold = {
    'scaling': [None, StandardScaler(), MinMaxScaler()],
    'krr__alpha': np.unique(np.append(param_grid['krr__alpha'], grid_krr.best_params_['krr__alpha'])),
    'krr__gamma': np.unique(np.append(param_grid['krr__gamma'], grid_krr.best_params_['krr__gamma'])),
    'variance_treshold__threshold': [0.0, 1e-4, 1e-2]
}

random_variance_treshold = RandomizedSearchCV(
    pipe_variance_threshold, param_distributions=param_grid_variance_threshold,
    n_iter=12, scoring='neg_mean_absolute_error', cv=cv, refit=True,
    random_state=RANDOM_SEED, verbose=2, n_jobs=20, pre_dispatch=20
)


In [28]:
# Fit the pipeline and run the evaluation.
random_variance_treshold.fit(X_train, y_train)
print(f'Best CV MAE = {-random_variance_treshold.best_score_:.3f} mmol/g')
pp.pprint(random_variance_treshold.best_params_)
variance_results = evaluate_regression_model(
    random_variance_treshold.best_estimator_, 'KRR — variance threshold'
)
selected_features = np.array(FEATURES)[
    random_variance_treshold.best_estimator_.named_steps['variance_treshold'].get_support()
]
print(f'Retained {len(selected_features)} of {len(FEATURES)} features')


Fitting 5 folds for each of 12 candidates, totalling 60 fits


[CV] END krr__alpha=10.0, krr__gamma=0.0001, scaling=MinMaxScaler(), variance_treshold__threshold=0.01; total time=  17.9s
[CV] END krr__alpha=10.0, krr__gamma=0.0001, scaling=MinMaxScaler(), variance_treshold__threshold=0.01; total time=  18.5s
[CV] END krr__alpha=10.0, krr__gamma=0.0001, scaling=MinMaxScaler(), variance_treshold__threshold=0.01; total time=  18.7s
[CV] END krr__alpha=0.1, krr__gamma=0.0001, scaling=StandardScaler(), variance_treshold__threshold=0.01; total time=  20.6s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=StandardScaler(), variance_treshold__threshold=0.01; total time=  23.2s
[CV] END krr__alpha=0.001, krr__gamma=0.0001, scaling=StandardScaler(), variance_treshold__threshold=0.01; total time=  23.7s
[CV] END krr__alpha=0.1, krr__gamma=0.0001, scaling=StandardScaler(), variance_treshold__threshold=0.01; total time=  24.2s
[CV] END krr__alpha=10.0, krr__gamma=0.01, scaling=MinMaxScaler(), variance_treshold__threshold=0.0; total time=  26.0s
[CV] END kr

Retained 138 of 164 features


$\color{DarkBlue}{\textsf{Short Exercise (optional)}}$
- replace the variance threshold with a model-based feature selection 
`('feature_selection', SelectFromModel(LinearSVC(penalty="l1")))` or [any feature selection method that you would like to try](https://scikit-learn.org/stable/modules/feature_selection.html)

## 9. Saving the model

Now, that we spent so much time in optimizing our model, we do not want to loose it. 

 $\color{DarkBlue}{\textsf{Short Exercise}}$
- use the [joblib library](https://scikit-learn.org/stable/modules/model_persistence.html) to save your model
- make sure you can load it again


In [29]:
# Choose the fitted pipeline by validation MAE, never by test performance.
searches = {
    'grid search': grid_krr,
    'random search': random_krr,
    'variance threshold': random_variance_treshold
}
best_search_name = max(searches, key=lambda name: searches[name].best_score_)
model = searches[best_search_name].best_estimator_
filename = 'co2_uptake_krr.joblib'
joblib.dump(model, filename)
print(f'Saved {best_search_name} pipeline to {filename}')


Saved variance threshold pipeline to co2_uptake_krr.joblib


In [30]:
# Reload the complete preprocessing/model pipeline and verify its predictions.
model_loaded = joblib.load(filename)
np.testing.assert_allclose(model_loaded.predict(X_test), model.predict(X_test))
print('Reloaded model gives the same test predictions.')


Reloaded model gives the same test predictions.


## 10. Influence of Regularization

 $\color{DarkBlue}{\textsf{Short Exercise}}$
- what happens if you set $\alpha$  to a really small or to large value? Why is this the case explain what the parameter means using the equation derived in the lectures?

 To test this, fix this value in one of your pipelines, retrain the models (re-optimizing the other hyperparameters) and rerun the performance evaluation.



<details>
<summary> <font color='green'>Click here for hints</font></summary>
<ul>
    <li> Check the derivation for ridge regression and KRR in the notes. </li>
    <li> Also remember the loss landscapes we discussed in the lectures about LASSO. </li>
</ul>
</details>

In [31]:
# Fix extreme alpha values and retune gamma, keeping the chosen preprocessing.
regularization_searches = {}
regularization_results = []
for alpha in [1e-8, 1e3]:
    alpha_search = GridSearchCV(
        clone(model).set_params(krr__alpha=alpha),
        param_grid={'krr__gamma': np.unique(np.append(
            np.logspace(-5, 1, 7), model.named_steps['krr'].gamma
        ))},
        scoring='neg_mean_absolute_error', cv=cv, refit=True,
        verbose=2, n_jobs=20, pre_dispatch=20
    )
    alpha_search.fit(X_train, y_train)
    regularization_searches[alpha] = alpha_search
    print(f"alpha = {alpha:g}, best gamma = {alpha_search.best_params_['krr__gamma']:.3g}, "
          f'CV MAE = {-alpha_search.best_score_:.3f} mmol/g')
    alpha_metrics = evaluate_regression_model(
        alpha_search.best_estimator_, f'KRR — alpha = {alpha:g}'
    )
    for split, metrics in alpha_metrics.items():
        regularization_results.append({'alpha': alpha, 'split': split, **metrics})

pd.DataFrame(regularization_results).set_index(['alpha', 'split'])


Fitting 5 folds for each of 8 candidates, totalling 40 fits


[CV] END ...................krr__gamma=9.999999999999999e-06; total time=  18.3s
[CV] END ....................................krr__gamma=0.01; total time=  20.6s
[CV] END ..................................krr__gamma=0.0001; total time=  21.9s
[CV] END ..................................krr__gamma=0.0001; total time=  21.9s
[CV] END ...................krr__gamma=9.999999999999999e-06; total time=  22.0s
[CV] END ...................................krr__gamma=0.001; total time=  22.4s
[CV] END ..................................krr__gamma=0.0001; total time=  23.5s
[CV] END ....................................krr__gamma=0.01; total time=  24.8s
[CV] END ...................krr__gamma=9.999999999999999e-06; total time=  26.0s
[CV] END ..................................krr__gamma=0.0001; total time=  27.0s
[CV] END ...................................krr__gamma=0.001; total time=  27.1s
[CV] END ...................................krr__gamma=0.001; total time=  27.7s
[CV] END ...................

Fitting 5 folds for each of 8 candidates, totalling 40 fits
[CV] END ..................................krr__gamma=0.0001; total time=  18.1s
[CV] END ...................krr__gamma=9.999999999999999e-06; total time=  19.5s
[CV] END ....................................krr__gamma=0.01; total time=  20.3s
[CV] END ..................................krr__gamma=0.0001; total time=  20.9s
[CV] END ....................................krr__gamma=0.01; total time=  22.7s
[CV] END ..................................krr__gamma=0.0001; total time=  23.8s
[CV] END ...................krr__gamma=9.999999999999999e-06; total time=  24.5s
[CV] END ...................................krr__gamma=0.001; total time=  24.8s
[CV] END ...................krr__gamma=9.999999999999999e-06; total time=  25.2s
[CV] END ....................................krr__gamma=0.01; total time=  26.8s
[CV] END ....................................krr__gamma=0.01; total time=  27.4s
[CV] END ...................krr__gamma=9.99999999

mae        mse  max_error
alpha        split                                
1.000000e-08 train  0.621964   0.809440   7.887005
             test   0.758830   1.818082  34.627523
1.000000e+03 train  3.403874  25.220528  28.174135
             test   3.311336  23.526944  26.832693

Kernel ridge regression minimizes
$$
\lVert y-Kc\rVert_2^2 + \alpha c^\mathsf{T}Kc,
\qquad c=(K+\alpha I)^{-1}y.
$$
The coefficient vector is `dual_coef_`. A small `alpha` weakly penalizes model complexity and may fit noise or make the linear system poorly conditioned. A large `alpha` shrinks the fitted function and can cause underfitting. With the uncentered targets and no intercept used here, predictions tend toward zero as `alpha` grows without bound. The training/test metrics below show the effect after retuning `gamma` for each fixed `alpha`; the best test performance need not occur at the smallest training error.


## 11. Interpreting the model 

Now, that our model performs decently, we would like to know which features are mainly responsible for this, i.e. how the model performs its reasoning. 

One method to do so is the [permutation feature importance technique](https://christophm.github.io/interpretable-ml-book/feature-importance.html).

$\color{DarkBlue}{\textsf{Short question}}$

We use both descriptors that encode the pore geometry (density, pore diameters, surface areas) as well as some that describe the chemistry of the MOF (the RACs). 
- Would you expect the relative importance of these features to be different for prediction of gas adsorption at high vs low gas pressure?



At low pressure, uptake is especially sensitive to adsorption affinity and strong binding sites, so descriptors of metal centers and functional groups can matter strongly. At high pressure, pore volume, surface area, density, and pore dimensions are expected to become more important as the pores fill. Thus, for the high-pressure CO₂ target used here, we expect geometric descriptors to feature strongly, although chemistry can still matter. These trends also depend on the diversity of the dataset. 


<details>
<summary> <font color='green'>Click here for a hint</font></summary>
<ul>
    <li> <a href="https://pubs.acs.org/doi/abs/10.1021/acs.chemmater.8b02257">An article from Diego et al.</a> (10.1021/acs.chemmater.8b02257) gives some hints.</li>
</ul>
</details>

 $\color{DarkBlue}{\textsf{Short Exercise}}$
- Complete the function `_calculate_permutation_scores` (which we took from the `sklearn` package) and which is needed to calculate the permutation feature importance using the `permutation_importance` function. 

In [32]:
def _calculate_permutation_scores(estimator, X, y, col_idx, random_state,
                                  n_repeats, scorer):
    """Calculate score when `col_idx` is permuted. Based on the sklearn implementation

    estimator: sklearn estimator object
    X: pd.Dataframe or np.array
    y: pd.Dataframe or np.array
    col_idx: int
    random_state: int
    n_repeats: int
    scorer: function that takes model, X and y_true as arguments
    """
    random_state = check_random_state(random_state)

    X_permuted = X.copy()
    scores = np.zeros(n_repeats)
    # get the indices
    shuffling_idx = np.arange(X.shape[0])
    for n_round in range(n_repeats):
        # Shuffle row indices to break the association with the target.
        random_state.shuffle(shuffling_idx)

        # Deal with dataframes
        if hasattr(X_permuted, "iloc"):
            # .iloc selects the indices from a dataframe and you give it [row, column]
            col = X_permuted.iloc[shuffling_idx, col_idx]
            col.index = X_permuted.index
            X_permuted.iloc[:, col_idx] = col

        # Deal with numpy arrays
        else:
            # array indexing is [row, column]
            X_permuted[:, col_idx] = X_permuted[shuffling_idx, col_idx]

        # Get the scores
        feature_score = scorer(estimator, X_permuted, y)

        # record the scores in array
        scores[n_round] = feature_score

    return scores

Nothing to change in the function below, it just call the `_calculate_permutation_scores` function you just completed. 

In [33]:
def permutation_importance(
    estimator,
    X,
    y,
    scoring="neg_mean_absolute_error",
    n_repeats=5,
    n_jobs=20,
    random_state=None,
):
    """Permutation importance for feature evaluation
    estimator : object
        An estimator that has already been :term:`fitted` and is compatible
        with :term:`scorer`.
    X : ndarray or DataFrame, shape (n_samples, n_features)
        Data on which permutation importance will be computed.
    y : array-like or None, shape (n_samples, ) or (n_samples, n_classes)
        Targets for supervised or `None` for unsupervised.
    scoring : string, callable or None, default=None
        Scorer to use. It can be a single
        string (see :ref:`scoring_parameter`) or a callable (see
        :ref:`scoring`). If None, the estimator's default scorer is used.
    n_repeats : int, default=5
        Number of times to permute a feature.
    n_jobs : int or None, default=2
        The number of jobs to use for the computation.
        `None` means 1 unless in a :obj:`joblib.parallel_backend` context.
        `-1` means using all processors. See :term:`Glossary <n_jobs>`
        for more details.
    random_state : int, RandomState instance, or None, default=None
        Pseudo-random number generator to control the permutations of each
        feature. See :term:`random_state`.
    """
    # Deal with dataframes
    if not hasattr(X, "iloc"):
        X = check_array(X, ensure_all_finite="allow-nan", dtype=None)

    # Precompute random seed from the random state to be used
    # to get a fresh independent RandomState instance for each
    # parallel call to _calculate_permutation_scores, irrespective of
    # the fact that variables are shared or not depending on the active
    # joblib backend (sequential, thread-based or process-based).
    random_state = check_random_state(random_state)
    random_seed = random_state.randint(np.iinfo(np.int32).max + 1)

    # Determine scorer from user options.
    scorer = check_scoring(estimator, scoring=scoring)
    # get the performance score on the unpermuted data
    baseline_score = scorer(estimator, X, y)

    # run the permuted evaluations in parallel for each column
    scores = Parallel(n_jobs=n_jobs)(
        delayed(_calculate_permutation_scores)(
            estimator, X, y, col_idx, random_seed, n_repeats, scorer
        )
        for col_idx in range(X.shape[1])
    )

    # get difference two
    importances = baseline_score - np.array(scores)

    # return the results (dictionary)
    return Bunch(
        importances_mean=np.mean(importances, axis=1),
        importances_std=np.std(importances, axis=1),
        importances=importances,
    )


 $\color{DarkBlue}{\textsf{Short Exercise}}$
- Use your function to find the five most important features.
- Which are they? Did you expect this result?



In [34]:
# Use a reproducible test subset to limit the cost of repeated KRR predictions.
# The model is already selected; these importances are for interpretation only.
importance_data = df_test_stratified.sample(
    n=min(200, len(df_test_stratified)), random_state=RANDOM_SEED
)
permutation_results = permutation_importance(
    model_loaded, importance_data[FEATURES], importance_data[TARGET],
    scoring='neg_mean_absolute_error', n_repeats=5, n_jobs=20,
    random_state=RANDOM_SEED
)
print(f'Permutation importance evaluated on {len(importance_data)} test materials.')


Permutation importance evaluated on 200 test materials.


In [35]:
# Positive importance means shuffling the feature increased MAE.
permutation_results['features'] = FEATURES
feature_importances = pd.DataFrame({
    'feature': FEATURES,
    'importance_mean': permutation_results['importances_mean'],
    'importance_std': permutation_results['importances_std']
}).sort_values('importance_mean', ascending=False)
top_five_features = feature_importances.head(5)
print('Five most important features (increase in MAE, mmol/g):')
print(top_five_features.to_string(index=False))

fig = go.Figure(go.Bar(
    x=top_five_features['importance_mean'], y=top_five_features['feature'],
    orientation='h',
    marker_color=sample_colorscale('Magma', np.linspace(0.2, 0.75, len(top_five_features))),
    error_x=dict(type='data', array=top_five_features['importance_std'], visible=True),
    customdata=top_five_features['importance_std'],
    hovertemplate=(
        '%{y}<br>Increase in MAE: %{x:.3f} mmol/g'
        '<br>Shuffle standard deviation: %{customdata:.3f} mmol/g<extra></extra>'
    ),
))
fig.update_yaxes(autorange='reversed')
fig.add_vline(x=0, line_color=sample_colorscale('Magma', [0.05])[0], line_dash='dash')
fig.update_layout(
    title='Five most important features — test subset', template='plotly_white',
    xaxis_title='Increase in MAE after permutation (mmol/g)', height=450,
    margin=dict(l=200), showlegend=False,
)
fig.show(config=PLOT_CONFIG)

n_geometric = top_five_features['feature'].isin(geometric_descriptors).sum()
print(f'{n_geometric} of the top five descriptors describe pore geometry.')


Five most important features (increase in MAE, mmol/g):
             feature  importance_mean  importance_std
       sum-f-lig-S-2         8.071096        0.350863
total_POV_volumetric         6.026607        0.225038
       sum-f-lig-S-0         4.855299        0.176339
 total_SA_volumetric         4.678521        0.393984
       sum-f-lig-I-0         3.871069        0.119938


2 of the top five descriptors describe pore geometry.


The five most important features in the results below are, in order, `sum-f-lig-S-2`, `total_POV_volumetric`, `sum-f-lig-S-0`, `total_SA_volumetric` and `sum-f-lig-I-0`. Shuffling them increases the MAE by about 8.071, 6.027, 4.855, 4.679 and 3.871 mmol/g, respectively.

This is a partly expected result. Pore volume and surface area are in the top five, which agrees with the idea that available pore space matters at high gas pressure. However, only two of the top five features are geometric descriptors, and the highest-ranked feature is a linker RAC. We expected geometry to dominate more strongly. The result suggests that the linker descriptors also provide useful information for this fitted model. They can reflect aspects of composition and structure, so their importance alone does not prove that chemical binding effects dominate adsorption.

This ranking is based on 200 test materials and five shuffles per feature, so it should not be treated as universal. Correlated descriptors can replace some of each other's information, which makes individual importances harder to interpret. The error bars show variation between shuffles, not confidence intervals.


<details>
<summary> <font color='green'>Click here for hints</font></summary>
<ul>
    <li> To get the top <emph>n</emph> indices of an array <code>a</code>, you can use <code>np.argsort(a)[-n:]</code></li>
    <li> Get the feature names from the <code>FEATURES</code> list </li> 
    <li> combined this might look like <code>np.array(FEATURES)[np.argsort(a)[-n:]]</code></li>
</ul>
</details>

<details>
<summary> <font color='green'>Click here for more information on model interpretation</font></summary>
The permutation feature importance technique is not a silver bullet, e.g. there are issues with correlated features.
However, it is likely <a href='https://explained.ai/rf-importance/'>a better choice than feature importance, like impurity decrease, derived from random forests</a>).
</details>